In [8]:
import geopandas as gpd
import pandas as pd
from shapely.geometry import Polygon
from shapely.geometry import MultiPolygon

In [9]:
catastro = gpd.read_file("../large_data/SLA Cadastral Land Parcel.geojson")
hdb = gpd.read_file("../large_data/HDBExistingBuilding.geojson")

In [10]:
import pandas as pd

def merge_small_clusters(clusters, min_area_m2=10_000):
    result = clusters.to_crs(3414).copy()
    result = result.set_index("cluster_id")
    result = result[["geometry"]].copy()

    # Track original IDs so building assignments can be updated
    result["original_ids"] = [[cid] for cid in result.index]

    while True:
        areas = result.geometry.area
        small_ids = areas[areas < min_area_m2].sort_values().index
        merged = False

        for source_id in small_ids:
            source = result.loc[source_id, "geometry"]

            # Only consider touching neighbours
            neighbours = result.loc[
                (result.index != source_id)
                & result.geometry.touches(source)
            ].copy()

            if neighbours.empty:
                continue

            # Prefer the longest shared boundary
            shared_boundary = neighbours.geometry.apply(
                lambda geom: source.boundary.intersection(geom.boundary).length
            )

            # Exclude clusters that only touch at a single point
            shared_boundary = shared_boundary[shared_boundary > 0]
            if shared_boundary.empty:
                continue

            target_id = shared_boundary.idxmax()

            result.at[target_id, "geometry"] = (
                result.at[target_id, "geometry"].union(source)
            )
            result.at[target_id, "original_ids"] = (
                result.at[target_id, "original_ids"]
                + result.at[source_id, "original_ids"]
            )

            result = result.drop(index=source_id)
            merged = True
            break  # Recalculate areas after each merge

        if not merged:
            break

    # Original cluster ID → merged cluster ID
    id_map = {
        original_id: merged_id
        for merged_id, row in result.iterrows()
        for original_id in row["original_ids"]
    }

    result = result.reset_index()
    result["area_m2"] = result.area

    return result, id_map

In [11]:
# 1. Give each original cadastral lot a unique ID
lots = catastro.reset_index(drop=True).copy()
lots["cluster_id"] = lots.index

# 2. Fill holes while preserving each lot's outer boundary
def fill_holes(geom):
    if geom is None or geom.is_empty:
        return geom
    if geom.geom_type == "Polygon":
        return Polygon(geom.exterior)
    if geom.geom_type == "MultiPolygon":
        return MultiPolygon([Polygon(p.exterior) for p in geom.geoms])
    return geom

lots.geometry = lots.geometry.apply(fill_holes)

# Singapore projected CRS, so areas are measured in square metres
lots = lots.to_crs(3414).copy()
lots = lots.drop_duplicates(subset="geometry").reset_index(drop=True)
lots["area_m2"] = lots.area

# Find lots contained inside other lots
nested = gpd.sjoin(
    lots[["geometry", "area_m2"]],
    lots[["geometry", "area_m2"]],
    how="inner",
    predicate="covered_by",
    lsuffix="inner",
    rsuffix="outer",
)

# Remove a lot only if its enclosing lot is larger
inner_ids = nested.loc[
    nested["area_m2_inner"] < nested["area_m2_outer"]
].index.unique()

outer_lots = lots.drop(index=inner_ids).copy()

# Assign HDB representative points to the remaining lots
buildings = hdb.to_crs(outer_lots.crs).reset_index(drop=True)
points = buildings[["geometry"]].copy()
points.geometry = points.geometry.representative_point()

matches = gpd.sjoin(
    points,
    outer_lots[["cluster_id", "geometry"]],
    how="left",
    predicate="covered_by",
)


clusters = outer_lots[
    outer_lots["cluster_id"].isin(matches["cluster_id"].dropna())
].copy()


# Create a NEW map so old HDB outlines are not retained
m = clusters.explore(
)

In [20]:
import geopandas as gpd
import pandas as pd
from IPython.display import display

MIN_AREA_M2 = 1_000 # 1 hectare


# 1. Resolve multiple matches per building
assigned = matches.dropna(subset=["cluster_id"]).copy()
assigned["building_id"] = assigned.index
assigned["lot_area"] = assigned["cluster_id"].map(
    outer_lots.set_index("cluster_id")["area_m2"]
)

assigned = (
    assigned.sort_values(["building_id", "lot_area", "cluster_id"])
    .drop_duplicates("building_id")
)

clusters = outer_lots[
    outer_lots["cluster_id"].isin(assigned["cluster_id"])
].copy()

# 2. Merge small clusters and update assignments
n_before = len(clusters)
clusters, id_map = merge_small_clusters(clusters, MIN_AREA_M2)
assigned["cluster_id"] = assigned["cluster_id"].map(id_map)

sizes = assigned.groupby("cluster_id").size()
clusters["n_buildings"] = clusters["cluster_id"].map(sizes).astype(int)

hdb_clustered = buildings.to_crs(3414).copy()
hdb_clustered["cluster_id"] = hdb_clustered.index.map(
    assigned.set_index("building_id")["cluster_id"]
)

# 3. Calculate centroids of the final merged clusters
centroids = gpd.GeoDataFrame(
    clusters[["cluster_id", "n_buildings"]].copy(),
    geometry=clusters.geometry.centroid,
    crs=clusters.crs,
)

centroids_wgs84 = centroids.to_crs(4326)
centroids["longitude"] = centroids_wgs84.geometry.x
centroids["latitude"] = centroids_wgs84.geometry.y

# Building-centroid → final cluster-centroid distances, in metres
centre_lookup = centroids.set_index("cluster_id").geometry
assigned_blocks = hdb_clustered.dropna(subset=["cluster_id"]).copy()

assigned_blocks["centroid_error_m"] = [
    geom.centroid.distance(centre_lookup.loc[cid])
    for geom, cid in zip(
        assigned_blocks.geometry, assigned_blocks["cluster_id"]
    )
]

# 4. Print statistics for the final clusters
print(f"Clusters before merging: {n_before:,}")
print(f"Clusters after merging: {len(clusters):,}")
print(
    f"Clusters still below {MIN_AREA_M2:,.0f} m²: "
    f"{(clusters['area_m2'] < MIN_AREA_M2).sum():,}"
)
print(f"Total HDB buildings: {len(hdb_clustered):,}")
print(f"Assigned buildings: {len(assigned_blocks):,}")
print(f"Unassigned buildings: {hdb_clustered['cluster_id'].isna().sum():,}")

if not assigned_blocks.empty:
    errors = assigned_blocks["centroid_error_m"]

    summary = pd.DataFrame([{
        "Option": f"Cadastral clusters, merge below {MIN_AREA_M2:,.0f} m²",
        "Clusters": len(clusters),
        "Largest cluster": f"{sizes.max():,} blocks",
        "Median cluster": f"{sizes.median():,.1f} blocks",
        "Mean centroid error": f"{errors.mean():,.0f} m",
        "95th-pct error": f"{errors.quantile(0.95):,.0f} m",
        "Maximum error": f"{errors.max():,.0f} m",
    }])

    display(summary)

# 5. Display final clusters and centroids
if not clusters.empty:
    m = clusters.explore(
        tooltip=["cluster_id", "n_buildings", "area_m2"],
        style_kwds={"fillOpacity": 0.2, "weight": 2},
    )

    centroids.explore(
        m=m,
        color="black",
        marker_kwds={"radius": 5},
        tooltip=["cluster_id", "n_buildings", "latitude", "longitude"],
    )

    display(m)

Clusters before merging: 2,133
Clusters after merging: 2,081
Clusters still below 1,000 m²: 18
Total HDB buildings: 13,436
Assigned buildings: 13,436
Unassigned buildings: 0


,Option,Clusters,Largest cluster,Median cluster,Mean centroid error,95th-pct error,Maximum error
0,"Cadastral clusters, merge below 1,000 m²",2081,111 blocks,5.0 blocks,92 m,217 m,960 m


In [21]:
# 5. New map with separate cluster outlines and centroid markers
m = clusters.explore(
    column="cluster_id",
    categorical=True,
    style_kwds={"fillOpacity": 0.25, "weight": 2},
)

centroids.explore(
    m=m,
    color="black",
    marker_kwds={"radius": 4},
)

In [22]:
clusters.to_file("../large_data/cadastral_lots_exp.geojson", driver="GeoJSON")

In [23]:
## stats 
import pandas as pd
from IPython.display import display

# Optional: set this to your column containing the number of flats per block
FLATS_COL = None  # e.g. "total_dwelling_units"

blocks = hdb_clustered.to_crs(3414).copy()
centres = centroids.to_crs(3414).set_index("cluster_id").geometry

assigned = blocks[blocks["cluster_id"].notna()].copy()

if assigned.empty:
    print("No HDB buildings have been assigned to clusters.")
else:
    # Distance from each building centroid to its cluster centroid
    assigned["centroid_error_m"] = [
        building.centroid.distance(centres.loc[cluster_id])
        for building, cluster_id in zip(
            assigned.geometry, assigned["cluster_id"]
        )
    ]

    # Number of buildings per cluster
    sizes = assigned.groupby("cluster_id").size()
    errors = assigned["centroid_error_m"]

    median_label = f"{sizes.median():,.1f} blocks"

    if FLATS_COL is not None:
        assigned[FLATS_COL] = pd.to_numeric(
            assigned[FLATS_COL], errors="coerce"
        )
        flats = assigned.groupby("cluster_id")[FLATS_COL].sum(min_count=1)
        median_label += f", {flats.median():,.0f} flats"

    # Illustrative straight-line walking equivalent: 80 metres/minute
    def distance_label(distance):
        return f"{distance:,.0f} m (~{distance / 80:.1f} min)"

    summary = pd.DataFrame([{
        "Option": "Cadastral lot clusters",
        "Clusters": f"{len(sizes):,}",
        "Largest cluster": f"{sizes.max():,} blocks",
        "Median cluster": median_label,
        "Mean centroid error": distance_label(errors.mean()),
        "95th-pct error": distance_label(errors.quantile(0.95)),
    }])

    print(
        f"Assigned: {len(assigned):,} / {len(blocks):,} buildings "
        f"({len(assigned) / len(blocks):.1%})"
    )
    print(f"Unassigned: {blocks['cluster_id'].isna().sum():,}")
    print(f"Single-building clusters: {(sizes == 1).sum():,}")
    print(f"Maximum centroid error: {errors.max():,.0f} m")

    display(summary)

Assigned: 13,436 / 13,436 buildings (100.0%)
Unassigned: 0
Single-building clusters: 540
Maximum centroid error: 960 m


,Option,Clusters,Largest cluster,Median cluster,Mean centroid error,95th-pct error
0,Cadastral lot clusters,"2,081",111 blocks,5.0 blocks,92 m (~1.1 min),217 m (~2.7 min)
